# Część II: osadzenia słów i tekstów

Korpus: zaanotowane fragmenty wystąpień sejmowych (`annotations/rest-annotations.json`). Etykiety z części I:
- **`ton`** (zwykły / agresywny): główny przedmiot analizy na tym etapie projektu,
- spany **`Agresja`** (frazy agresywne wewnątrz tekstów agresywnych),
- `stance` (popiera / neutralna / sprzeciwia się) i spany `Kontekst` (słowa, które przesądziły o postawie): analiza pomocnicza.

Modele:
- **Word2Vec**: IPI PAN, NKJP + Wikipedia, formy wyrazowe, skip-gram, 300 wymiarów,
- **fastText**: Facebook, Common Crawl + Wikipedia, `cc.pl.300.bin` (n-gramy znakowe, wektor także dla słów spoza słownika).

Redukcja wymiarowości: **t-SNE** (nienadzorowana, pokazuje, czy etykiety same wyłaniają się ze struktury przestrzeni) i **LDA**, czyli liniowa analiza dyskryminacyjna (nadzorowana, szuka kierunku najlepiej rozdzielającego agresję od zwykłego tonu).

In [1]:
import csv
import json
import re
import textwrap

import fasttext
import numpy as np
import pandas as pd
import plotly.express as px
import plotly.io as pio
from sklearn.discriminant_analysis import LinearDiscriminantAnalysis
from sklearn.feature_extraction.text import TfidfVectorizer
from sklearn.linear_model import LogisticRegression
from sklearn.manifold import TSNE
from sklearn.metrics import roc_auc_score, silhouette_score
from sklearn.model_selection import StratifiedKFold, cross_val_predict, cross_validate
from sklearn.neighbors import KNeighborsClassifier

pio.renderers.default = "plotly_mimetype+notebook_connected"
pd.set_option("display.max_colwidth", 200)

ANNOTATIONS = ["annotations/rest-annotations.json"]
W2V_PATH = "models/nkjp+wiki-forms-all-300-skipg-ns-50.txt.gz"
FT_PATH = "models/cc.pl.300.bin"
K = 10
SEED = 42
cv = StratifiedKFold(5, shuffle=True, random_state=SEED)
AGG, REST = "Agresja (span)", "poza spanami Agresja"
TON_COLORS = {"agresywny": "#d62728", "zwykły": "#9e9e9e"}
STANCE_COLORS = {"popiera": "#2ca02c", "neutralna": "#1f77b4", "sprzeciwia się": "#ff7f0e"}

## Dane

In [2]:
docs = pd.concat([pd.DataFrame(json.load(open(p))) for p in ANNOTATIONS]).drop_duplicates("text").reset_index(drop=True)
docs["spans"] = docs.spans.apply(lambda s: s if isinstance(s, list) else [])
docs[["speaker", "club", "date"]] = docs.meta.str.split(" · ", expand=True)

TOKEN = re.compile(r"\w+")
docs["n_tokens"] = docs.text.map(lambda t: len(TOKEN.findall(t)))
print(len(docs), "tekstów")
display(pd.crosstab(docs.stance, docs.ton, margins=True, margins_name="razem"))
display(docs.groupby("ton").n_tokens.describe().round(1))

600 tekstów


ton,agresywny,zwykły,razem
stance,,,
neutralna,9,116,125
popiera,27,232,259
sprzeciwia się,134,82,216
razem,170,430,600


,count,mean,std,min,25%,50%,75%,max
ton,,,,,,,,
agresywny,170.0,53.9,18.8,25.0,37.0,53.5,69.8,88.0
zwykły,430.0,52.1,18.3,21.0,36.2,49.5,65.8,90.0


In [3]:
pd.crosstab(docs.club, docs.ton, normalize="index").mul(100).round(1).sort_values("agresywny", ascending=False)

ton,agresywny,zwykły
club,,
PiS,48.0,52.0
Konfederacja,41.0,59.0
KO,38.0,62.0
Lewica,17.0,83.0
Polska2050-TD,15.0,85.0
PSL-TD,11.0,89.0


### Słowa a agresja

Etykieta słowa pochodzi ze spanów: słowo jest **`Agresja`**, jeśli co najmniej połowa jego wystąpień leży w spanach `Agresja`
(dzięki temu słowa funkcyjne, które czasem trafiają do spanu, nie dostają tej etykiety). Bierzemy wszystkie słowa treściowe bez progu częstości:
słowa ze spanów `Agresja` są prawie zawsze rzadkie, a porównanie ich tylko z częstymi słowami mierzyłoby różnicę częstości, a nie agresji.

Dodatkowo, dla porównania, liczymy statystyczny związek słowa z tonem tekstu: ważony log-odds (z-score) występowania w tekstach agresywnych vs zwykłych.

In [4]:
STOP = set('''i w we z ze na do o od po za u a oraz lub albo ale że żeby aby by się nie to jest są był była było byli były
będzie będą tak jak już też także tylko jeszcze czy co który która które którzy którego której którym którą których
ten ta te tego tej tym tych tę ich go mu mi mnie nas nam wam was wy my on ona oni one ono im jej jego
pan pani państwo państwa panie pana panu panią panów pań panowie proszę bardzo dziękuję
przez dla pod nad przed między bez przy jako więc bo gdy jeśli jeżeli kiedy gdzie tu tam tutaj teraz
może można trzeba mamy mają ma mieć mam być nich nim niej niego nią sobie wszystko wszyscy każdy
roku lat rok'''.split())


def span_label(doc, start, end):
    for s in doc.spans:
        if start < s["end"] and s["start"] < end:
            return s["labels"][0]


occ = pd.DataFrame(
    {"word": m.group().lower(), "span": span_label(d, m.start(), m.end()), "stance": d.stance, "ton": d.ton}
    for d in docs.itertuples()
    for m in TOKEN.finditer(d.text)
)

counts = occ.groupby(["word", "ton"]).size().unstack(fill_value=0)
a, z = counts["agresywny"], counts["zwykły"]
A, Z, V = a.sum(), z.sum(), len(counts)
delta = np.log((a + 1) / (A + V - a - 1)) - np.log((z + 1) / (Z + V - z - 1))
words = pd.DataFrame({"count": a + z, "w agresywnych": a, "z": delta / np.sqrt(1 / (a + 1) + 1 / (z + 1))})
words["w spanach Agresja"] = occ.groupby("word").span.agg(lambda s: (s == "Agresja").mean())
words["agresja"] = np.where(words["w spanach Agresja"] >= 0.5, AGG, REST)

ctx = occ[occ.span == "Kontekst"].groupby("word").stance.agg(lambda s: s.mode()[0])
words["kontekst"] = ("Kontekst: " + ctx).reindex(words.index).fillna("poza spanami")

content = words[(words.index.str.len() > 2)
                & ~words.index.isin(STOP) & ~words.index.str.isdigit()]
print(f"tokenów: {len(occ)}, typów: {len(words)}, typów treściowych: {len(content)}")
display(content.agresja.value_counts())
print("najczęstsze słowa ze spanów Agresja:")
display(content[content.agresja == AGG].sort_values("count", ascending=False).head(20))
print("słowa najsilniej związane statystycznie z tekstami agresywnymi:")
content.sort_values("z", ascending=False).head(15)

tokenów: 31584, typów: 9148, typów treściowych: 8824


agresja
poza spanami Agresja    8423
Agresja (span)           401
Name: count, dtype: int64

najczęstsze słowa ze spanów Agresja:


,count,w agresywnych,z,w spanach Agresja,agresja,kontekst
word,,,,,,
apeluję,5,4,1.746231,0.600000,Agresja (span),Kontekst: sprzeciwia się
koalicję,4,3,1.429292,0.500000,Agresja (span),Kontekst: neutralna
chaos,4,2,0.666959,0.500000,Agresja (span),Kontekst: popiera
społeczeństwo,4,3,1.429292,0.500000,Agresja (span),Kontekst: popiera
nieudolności,3,3,1.727123,0.666667,Agresja (span),Kontekst: popiera
rozumiecie,3,3,1.727123,0.666667,Agresja (span),poza spanami
skok,3,3,1.727123,0.666667,Agresja (span),poza spanami
aferę,3,3,1.727123,1.000000,Agresja (span),poza spanami
stratę,3,2,1.040746,0.666667,Agresja (span),Kontekst: popiera


słowa najsilniej związane statystycznie z tekstami agresywnymi:


,count,w agresywnych,z,w spanach Agresja,agresja,kontekst
word,,,,,,
pis,26,24,4.363325,0.153846,poza spanami Agresja,Kontekst: sprzeciwia się
prezydenta,16,13,3.171201,0.000000,poza spanami Agresja,Kontekst: sprzeciwia się
ani,20,14,2.855869,0.000000,poza spanami Agresja,poza spanami
posłowie,18,13,2.853517,0.000000,poza spanami Agresja,poza spanami
waszego,8,8,2.601466,0.250000,poza spanami Agresja,Kontekst: popiera
rząd,30,18,2.568830,0.033333,poza spanami Agresja,Kontekst: popiera
raz,18,12,2.482958,0.055556,poza spanami Agresja,poza spanami
tusk,7,7,2.474259,0.000000,poza spanami Agresja,poza spanami
tuska,7,7,2.474259,0.000000,poza spanami Agresja,poza spanami


## Modele

In [5]:
w2v = pd.read_csv(W2V_PATH, sep=" ", header=None, skiprows=1, quoting=csv.QUOTE_NONE,
                  index_col=0, na_filter=False, dtype={0: str})
w2v_words = w2v.index.to_numpy()
w2v_index = {w: i for i, w in enumerate(w2v_words)}
W = w2v.to_numpy(np.float32)
W /= np.linalg.norm(W, axis=1, keepdims=True)
del w2v

ft = fasttext.load_model(FT_PATH)
in_w2v = lambda w: w in w2v_index
in_ft = lambda w: ft.get_word_id(w) != -1
print("Word2Vec:", W.shape, " fastText:", len(ft.words), "słów")
pd.DataFrame({
    "Word2Vec": [words.index.map(in_w2v).to_numpy().mean(), occ.word.map(in_w2v).mean()],
    "fastText": [words.index.map(in_ft).to_numpy().mean(), occ.word.map(in_ft).mean()],
}, index=["pokrycie typów", "pokrycie tokenów"]).round(3)

Word2Vec: (556932, 300)  fastText: 2000000 słów


,Word2Vec,fastText
pokrycie typów,0.931,0.972
pokrycie tokenów,0.970,0.987


In [6]:
print("słowa agresywne spoza Word2Vec:", [w for w in content[content.agresja == AGG].index if not in_w2v(w)])
print("słowa agresywne spoza fastText:", [w for w in content[content.agresja == AGG].index if not in_ft(w)])

słowa agresywne spoza Word2Vec: ['autokompromitacja', 'berię', 'bonjour', 'budapeszcie', 'byliście', 'byście', 'dopychania', 'drenowaniu', 'giertych', 'jerzym', 'krztę', 'mierzcie', 'mniemanej', 'obajtek', 'odtrąbione', 'okłamujecie', 'ostrołęka', 'patowładzę', 'podkupi', 'podratował', 'pogłębiacie', 'poklepali', 'pozbawiliście', 'przebierańcach', 'przypinką', 'przywróciliście', 'putinflacja', 'rdzewiejąca', 'rozumkami', 'ukrywaliście', 'urbanem', 'zafundowaliście', 'zagłosowaliście', 'zandberg', 'zawaliliście', 'zniesławiona', 'złożyliście']
słowa agresywne spoza fastText: ['autokompromitacja', 'berię', 'dopychania', 'jerzym', 'obajtek', 'odtrąbione', 'okłamujecie', 'patowładzę', 'podratował', 'pogłębiacie', 'poklepali', 'pozbawiliście', 'przebierańcach', 'przywróciliście', 'putinflacja', 'półinteligent', 'rdzewiejąca', 'rozumkami', 'ukrywaliście', 'urbanem', 'zafundowaliście', 'zagłosowaliście', 'zandberg', 'zawaliliście', 'zniesławiona']


## Osadzenia słów

In [7]:
vocab = content[content.index.map(in_w2v) & content.index.map(in_ft)].copy()
word_vecs = {
    "Word2Vec": np.stack([W[w2v_index[w]] for w in vocab.index]),
    "fastText": np.stack([ft.get_word_vector(w) for w in vocab.index]),
}


def unit(X):
    return X / np.linalg.norm(X, axis=1, keepdims=True)


def tsne(X, perplexity=30):
    return TSNE(perplexity=perplexity, metric="cosine", init="pca", random_state=SEED).fit_transform(X)


word_xy = {name: tsne(X) for name, X in word_vecs.items()}
print(len(vocab), "słów na wykresach")

8179 słów na wykresach


### t-SNE: agresja

In [8]:
AGG_COLORS = {AGG: "#d62728", REST: "#d0d0d0"}
for name, xy in word_xy.items():
    fig = px.scatter(vocab.assign(x=xy[:, 0], y=xy[:, 1], słowo=vocab.index), x="x", y="y", color="agresja",
                     color_discrete_map=AGG_COLORS, category_orders={"agresja": [REST, AGG]},
                     hover_name="słowo", hover_data={"count": True, "w spanach Agresja": ":.2f", "w agresywnych": True,
                                                     "z": ":.2f", "kontekst": True, "x": False, "y": False},
                     title=f"t-SNE słów: {name}, kolor = słowo ze spanów Agresja", width=950, height=700)
    fig.update_traces(marker=dict(size=7, opacity=0.85))
    fig.show()

### LDA: słowa ze spanów Agresja vs pozostałe

LDA uczona na wszystkich danych zawsze „rozdzieli” klasy w 300 wymiarach, nawet gdy etykiety są losowe. Dlatego pokazujemy **wyniki poza próbą**:
każde słowo jest rzutowane przez LDA uczoną na pozostałych 4/5 słów (5-krotna walidacja krzyżowa, LDA z regularyzacją `shrinkage="auto"`).
Miarą rozdzielenia jest AUC (0,5 = brak rozdzielenia, 1 = pełne).

In [9]:
def lda_scores(X, y):
    lda = LinearDiscriminantAnalysis(solver="lsqr", shrinkage="auto")
    return cross_val_predict(lda, X, y, cv=cv, method="decision_function")


def lda_plot(frame, score, y, positive, color_map, hover, title):
    auc = roc_auc_score(y == positive, score)
    jitter = np.random.default_rng(SEED).uniform(-1, 1, len(frame))
    fig = px.scatter(frame.assign(LDA=score, jitter=jitter), x="LDA", y="jitter", color=y, color_discrete_map=color_map,
                     hover_name=hover, hover_data={"jitter": False, "LDA": ":.2f"}, marginal_x="histogram",
                     title=f"{title} (AUC poza próbą = {auc:.3f})", width=950, height=500, opacity=0.75)
    fig.update_yaxes(visible=False, row=1, col=1)
    fig.show()
    return auc


word_lda_auc = {}
for name, X in word_vecs.items():
    score = lda_scores(unit(X), vocab.agresja.to_numpy())
    word_lda_auc[name] = lda_plot(vocab.assign(słowo=vocab.index), -score, vocab.agresja.to_numpy(), AGG,
                                  AGG_COLORS, "słowo", f"LDA słów: {name}, Agresja vs pozostałe")

In [10]:
rows = []
for name, X in word_vecs.items():
    row = {"model": name, "LDA AUC: Agresja vs pozostałe": word_lda_auc[name]}
    rare = (vocab["count"] <= 2).to_numpy()
    row["LDA AUC: tylko słowa z 1–2 wystąpieniami"] = roc_auc_score(
        vocab.agresja[rare] == AGG, -lda_scores(unit(X[rare]), vocab.agresja[rare].to_numpy()))
    row["silhouette: Agresja vs pozostałe"] = silhouette_score(X, vocab.agresja, metric="cosine")
    m = vocab.kontekst.isin(["Kontekst: popiera", "Kontekst: sprzeciwia się"]).to_numpy()
    row["silhouette: Kontekst popiera vs sprzeciw"] = silhouette_score(X[m], vocab.kontekst[m], metric="cosine")
    rows.append(row)
pd.DataFrame(rows).set_index("model").T.round(3)

model,Word2Vec,fastText
LDA AUC: Agresja vs pozostałe,0.843,0.832
LDA AUC: tylko słowa z 1–2 wystąpieniami,0.819,0.815
silhouette: Agresja vs pozostałe,0.015,0.020
silhouette: Kontekst popiera vs sprzeciw,0.002,0.004


### t-SNE: Kontekst (postawa)

In [11]:
KTX_COLORS = {"Kontekst: popiera": "#2ca02c", "Kontekst: sprzeciwia się": "#ff7f0e",
              "Kontekst: neutralna": "#1f77b4", "poza spanami": "#e0e0e0"}
for name, xy in word_xy.items():
    fig = px.scatter(vocab.assign(x=xy[:, 0], y=xy[:, 1], słowo=vocab.index), x="x", y="y", color="kontekst",
                     color_discrete_map=KTX_COLORS, category_orders={"kontekst": list(KTX_COLORS)[::-1]},
                     hover_name="słowo", hover_data={"count": True, "agresja": True, "x": False, "y": False},
                     title=f"t-SNE słów: {name}, kolor = postawa tekstu dla słów ze spanów Kontekst", width=950, height=700)
    fig.update_traces(marker=dict(size=7, opacity=0.85))
    fig.show()

### Antonimy i synonimy

In [12]:
PAIRS = [("dobry", "zły"), ("sukces", "porażka"), ("prawda", "kłamstwo"), ("poprzeć", "odrzucić"),
         ("popieramy", "krytykujemy"), ("uczciwy", "nieuczciwy"),
         ("dobry", "świetny"), ("kłamstwo", "oszustwo"), ("skandal", "afera"), ("porażka", "klęska")]


def w2v_sim(a, b):
    return float(W[w2v_index[a]] @ W[w2v_index[b]]) if in_w2v(a) and in_w2v(b) else np.nan


def ft_sim(a, b):
    va, vb = ft.get_word_vector(a), ft.get_word_vector(b)
    return float(va @ vb / np.linalg.norm(va) / np.linalg.norm(vb))


pd.DataFrame([{"para": f"{a} – {b}", "relacja": "antonimy" if i < 6 else "synonimy",
               "Word2Vec": w2v_sim(a, b), "fastText": ft_sim(a, b)} for i, (a, b) in enumerate(PAIRS)]).round(3)

,para,relacja,Word2Vec,fastText
0,dobry – zły,antonimy,0.644,0.759
1,sukces – porażka,antonimy,0.387,0.451
2,prawda – kłamstwo,antonimy,0.373,0.433
3,poprzeć – odrzucić,antonimy,0.562,0.597
4,popieramy – krytykujemy,antonimy,0.509,0.688
5,uczciwy – nieuczciwy,antonimy,0.534,0.707
6,dobry – świetny,synonimy,0.761,0.762
7,kłamstwo – oszustwo,synonimy,0.642,0.721
8,skandal – afera,synonimy,0.572,0.548
9,porażka – klęska,synonimy,0.653,0.694


### k najbardziej podobnych słów

Zapytania: 10 najczęstszych słów ze spanów `Agresja` i 10 najczęstszych słów ze spanów `Kontekst`.
Nakładanie = część wspólna list top-K obu modeli (po sprowadzeniu do małych liter) / K.

In [13]:
def w2v_neighbors(w, k=K):
    sims = W @ W[w2v_index[w]]
    idx = np.argpartition(-sims, k + 1)[: k + 1]
    return [w2v_words[i] for i in idx[np.argsort(-sims[idx])] if w2v_words[i] != w][:k]


def ft_neighbors(w, k=K):
    return [n for _, n in ft.get_nearest_neighbors(w, k)]


def top_span_words(label, n=10):
    return occ[(occ.span == label) & occ.word.isin(vocab.index)].word.value_counts().head(n).index


agg_words = [w for w in top_span_words("Agresja", 50) if vocab.agresja[w] == AGG][:10]
queries = [("Agresja", w) for w in agg_words] + [("Kontekst", w) for w in top_span_words("Kontekst")]
rows = []
for group, w in queries:
    a, b = w2v_neighbors(w), ft_neighbors(w)
    rows.append({"słowo": w, "grupa": group, "z": vocab.z[w], "Word2Vec": ", ".join(a), "fastText": ", ".join(b),
                 "nakładanie": len({x.lower() for x in a} & {x.lower() for x in b}) / K})
neighbors = pd.DataFrame(rows).set_index("słowo")
print("średnie nakładanie list:", neighbors.groupby("grupa").nakładanie.mean().round(3).to_dict())
neighbors.round(2)

średnie nakładanie list: {'Agresja': 0.52, 'Kontekst': 0.34}


,grupa,z,Word2Vec,fastText,nakładanie
słowo,,,,,
apeluję,Agresja,1.75,"apelujemy, zaapelować, apeluje, apelują, zwracam, zaapelował, apelować, zaapelowali, apelował, apelując","Apeluję, apelujemy, zaapeluję, apeluje, apelowałbym, apelują, zaapelować, Apelujemy, apelować, apelowałem",0.5
aferę,Agresja,1.73,"aferą, afery, afera, korupcyjną, aferze, korupcję, łapówkarską, korupcyjny, zamieszany, przekręty","aferkę, afere, Aferę, aferą, afera, afery, awanturę, aferze, zadymę, aferki",0.4
rozumiecie,Agresja,1.73,"wiecie, widzicie, wy, zrozumiecie, rozumiesz, mówicie, pojmujecie, piszecie, kumam, powiedzcie","zrozumiecie, zrozumieliście, Rozumiecie, widzicie, Zrozumiecie, pojmiecie, wiecie, rozumieliście, mówicie, pojmujecie",0.5
siedzieć,Agresja,1.42,"przesiadywać, siedziec, posiedzieć, usiąść, siadać, leżeć, przesiedzieć, sterczeć, łazić, siedząc","siedziec, siadać, przesiadywać, przesiedzieć, siedzić, leżeć, usiąść, chodzić, Siedzieć, odpoczywać",0.6
więzieniu,Agresja,1.42,"areszcie, wiezieniu, więzieniach, więzienia, śledczym, łagrze, więziony, obozie, celi, poprawczaku","areszcie, wiezieniu, więzieniach, Więzieniu, więziennym, więzienia, uwięzieniu, więzieniu., więzieniem, wiêzieniu",0.4
chaos,Agresja,0.67,"bałagan, zamęt, haos, rozgardiasz, nieporządek, galimatias, nieład, marazm, bezład, terror","bałagan, haos, zamęt, chaos., nieporządek, nieład, bajzel, rozgardiasz, Chaos, bałagan.",0.6
skok,Agresja,1.73,"skoku, Skok, skoki, skokiem, skoczył, wzwyż, skoków, tyczce, pchnięcie, trójskok","Skok, skoku, podskok, wskok, skoki, skokiem, Zeskok, przeskok, zeskok, skoków",0.5
próbował,Agresja,1.42,"usiłował, starał, zamierzał, zdołał, postanowił, spróbował, potrafił, próbując, chciał, próbowali","usiłował, spróbował, probował, starał, Próbował, chciał, próbowałby, potrafił, próbuje, próbowała",0.5
nieudolności,Agresja,1.73,"niekompetencji, indolencji, niefrasobliwości, nieporadności, opieszałości, nieodpowiedzialności, arogancji, nadgorliwości, bezmyślności, niemocy","niekompetencji, nieudolnosci, nieporadności, bezmyślności, bezradności, opieszałości, ignorancji, indolencji, nieudolność, nadgorliwości",0.6


Czy sąsiedzi słów agresywnych też są agresywni? Dla każdego słowa ze spanów `Agresja` sprawdzamy, jaka część jego 10 najbliższych sąsiadów **w naszym słowniku** to także słowa ze spanów `Agresja`, w porównaniu z odsetkiem takich słów w słowniku.

In [14]:
rows = []
base = (vocab.agresja == AGG).mean()
for name, X in word_vecs.items():
    S = unit(X) @ unit(X).T
    np.fill_diagonal(S, -np.inf)
    nn = np.argsort(-S, axis=1)[:, :K]
    is_agg = (vocab.agresja == AGG).to_numpy()
    rows.append({"model": name, "odsetek słów Agresja w słowniku": base,
                 "sąsiedzi Agresja wśród słów Agresja": is_agg[nn[is_agg]].mean(),
                 "sąsiedzi Agresja wśród pozostałych słów": is_agg[nn[~is_agg]].mean()})
pd.DataFrame(rows).set_index("model").round(3)

,odsetek słów Agresja w słowniku,sąsiedzi Agresja wśród słów Agresja,sąsiedzi Agresja wśród pozostałych słów
model,,,
Word2Vec,0.044,0.134,0.031
fastText,0.044,0.123,0.028


## Osadzenia tekstów

- **Word2Vec (średnia)**: średnia znormalizowanych wektorów słów obecnych w słowniku,
- **fastText (sentence vector)**: `get_sentence_vector` na tokenizowanym tekście (średnia znormalizowanych wektorów, słowa spoza słownika z n-gramów).

In [15]:
PUNCT_TOKEN = re.compile(r"\w+|[^\w\s]")


def w2v_text(text):
    return np.mean([W[w2v_index[t]] for t in (x.lower() for x in TOKEN.findall(text)) if in_w2v(t)], axis=0)


def ft_text(text):
    return ft.get_sentence_vector(" ".join(PUNCT_TOKEN.findall(text)))


TEXT_MODELS = {"Word2Vec (średnia)": w2v_text, "fastText (sentence vector)": ft_text}
text_vecs = {name: np.stack(docs.text.map(f)) for name, f in TEXT_MODELS.items()}
text_xy = {name: tsne(X) for name, X in text_vecs.items()}
hover = docs.assign(tekst=docs.text.map(lambda t: "<br>".join(textwrap.wrap(t, 90))))

### t-SNE: ton

In [16]:
for name, xy in text_xy.items():
    fig = px.scatter(hover.assign(x=xy[:, 0], y=xy[:, 1]), x="x", y="y", color="ton", color_discrete_map=TON_COLORS,
                     category_orders={"ton": ["zwykły", "agresywny"]}, hover_name="meta",
                     hover_data={"stance": True, "tekst": True, "x": False, "y": False},
                     title=f"t-SNE tekstów: {name}, kolor = ton", width=950, height=650)
    fig.update_traces(marker=dict(size=8, opacity=0.8))
    fig.show()

### LDA: teksty agresywne vs zwykłe (poza próbą)

In [17]:
text_lda_auc = {}
for name, X in text_vecs.items():
    score = lda_scores(unit(X), docs.ton.to_numpy())
    text_lda_auc[name] = lda_plot(hover, -score, docs.ton.to_numpy(), "agresywny", TON_COLORS, "meta",
                                  f"LDA tekstów: {name}, agresywny vs zwykły")

### t-SNE: postawa

In [18]:
for name, xy in text_xy.items():
    fig = px.scatter(hover.assign(x=xy[:, 0], y=xy[:, 1]), x="x", y="y", color="stance", color_discrete_map=STANCE_COLORS,
                     hover_name="meta", hover_data={"ton": True, "tekst": True, "x": False, "y": False},
                     title=f"t-SNE tekstów: {name}, kolor = postawa", width=950, height=650)
    fig.update_traces(marker=dict(size=8, opacity=0.8))
    fig.show()

### Podobieństwo a etykiety

In [19]:
def sims(X):
    Xn = unit(X)
    return Xn @ Xn.T


iu = np.triu_indices(len(docs), 1)
pairs, rows = {}, []
for name, X in text_vecs.items():
    S = sims(X)
    p = pd.DataFrame({"i": iu[0], "j": iu[1], "sim": S[iu]})
    for field in ("ton", "stance"):
        v = docs[field].to_numpy()
        p[f"same_{field}"] = v[p.i] == v[p.j]
    p["both_agg"] = (docs.ton.to_numpy()[p.i] == "agresywny") & (docs.ton.to_numpy()[p.j] == "agresywny")
    pairs[name] = p
    rows.append({"model": name, "średnie podobieństwo": p.sim.mean(),
                 "ton: oba agresywne": p[p.both_agg].sim.mean(),
                 "ton: oba zwykłe": p[p.same_ton & ~p.both_agg].sim.mean(),
                 "ton: różny": p[~p.same_ton].sim.mean(),
                 "ton: silhouette": silhouette_score(X, docs.ton, metric="cosine"),
                 "stance: ta sama": p[p.same_stance].sim.mean(),
                 "stance: różna": p[~p.same_stance].sim.mean(),
                 "stance: silhouette": silhouette_score(X, docs.stance, metric="cosine")})
pd.DataFrame(rows).set_index("model").T.round(3)

model,Word2Vec (średnia),fastText (sentence vector)
średnie podobieństwo,0.811,0.810
ton: oba agresywne,0.832,0.848
ton: oba zwykłe,0.809,0.803
ton: różny,0.809,0.812
ton: silhouette,0.032,0.016
stance: ta sama,0.819,0.820
stance: różna,0.806,0.805
stance: silhouette,-0.009,-0.014


In [20]:
def show_pairs(p, n=5):
    p = p.head(n)
    return pd.DataFrame({
        "sim": p.sim.round(3).to_numpy(),
        "ton A / B": [f"{docs.ton[i]} / {docs.ton[j]}" for i, j in zip(p.i, p.j)],
        "postawa A / B": [f"{docs.stance[i]} / {docs.stance[j]}" for i, j in zip(p.i, p.j)],
        "tekst A": [docs.text[i][:160] for i in p.i],
        "tekst B": [docs.text[j][:160] for j in p.j],
    })


for name, p in pairs.items():
    print(name, "– najbardziej podobne pary o różnym tonie")
    display(show_pairs(p[~p.same_ton].sort_values("sim", ascending=False)))
    print(name, "– najbardziej podobne pary o przeciwnej postawie")
    opposite = (docs.stance.to_numpy()[p.i] != docs.stance.to_numpy()[p.j]) & ~p.same_stance \
        & (docs.stance.to_numpy()[p.i] != "neutralna") & (docs.stance.to_numpy()[p.j] != "neutralna")
    display(show_pairs(p[opposite].sort_values("sim", ascending=False)))

Word2Vec (średnia) – najbardziej podobne pary o różnym tonie


,sim,ton A / B,postawa A / B,tekst A,tekst B
0,0.950,zwykły / agresywny,popiera / sprzeciwia się,"Dzisiaj widzimy, że blisko 80% osób, które do nas przybyły i mogły podjąć pracę, tę pracę podjęły. To jest bardzo zdyscyplinowana grupa obywateli. Widzimy, że w","Zdajemy sobie oczywiście sprawę z tego, że potencjał naszej gospodarki cyfrowej jest gigantyczny, a tych zagrożeń, o czym mówią statystyki, dane przedstawiane r"
1,0.946,zwykły / agresywny,sprzeciwia się / sprzeciwia się,Państwo Izrael nie od dzisiaj łamie prawo międzynarodowe. Teraz jednak obserwujemy kryzys humanitarny na niewyobrażalną skalę. Nie zgadzam się ja i — jak sądzę,"Zdajemy sobie oczywiście sprawę z tego, że potencjał naszej gospodarki cyfrowej jest gigantyczny, a tych zagrożeń, o czym mówią statystyki, dane przedstawiane r"
2,0.943,agresywny / zwykły,popiera / popiera,"Dlaczego w tych dwóch sprawach jest tak emocjonalny protest? Jeżeli chodzi o zielony ład, to już mówiliśmy, że to jest emanacja programu PiS-u przeniesiona na j","Musi być cywilna kontrola nad Siłami Zbrojnymi i my musimy o to dbać, bo to jest interes nie tylko opozycji, ale i wszystkich. Musimy poważnie do tego podchodzi"
3,0.942,zwykły / agresywny,popiera / sprzeciwia się,"Należy podkreślić, że proponowane zmiany nie zamykają polskiego rynku zamówień publicznych, jeśli chodzi o wykonawców z państw trzecich, ale jasno wskazują to,","Zdajemy sobie oczywiście sprawę z tego, że potencjał naszej gospodarki cyfrowej jest gigantyczny, a tych zagrożeń, o czym mówią statystyki, dane przedstawiane r"
4,0.942,zwykły / agresywny,sprzeciwia się / sprzeciwia się,"Zabrakło mi czasu podczas wystąpienia klubowego, więc poruszę dwie ważne kwestie w czasie tej sekwencji pytań. Panie Ministrze! Pierwsza sprawa. Mówił pan w swo","Panie Marszałku! Wysoka Izbo! Chciałabym poinformować Wysoką Izbę, że nie jest przestrzegana ustawa o Funduszu rozwoju przewozów autobusowych. W tej ustawie w a"


Word2Vec (średnia) – najbardziej podobne pary o przeciwnej postawie


,sim,ton A / B,postawa A / B,tekst A,tekst B
0,0.950,zwykły / agresywny,popiera / sprzeciwia się,"Dzisiaj widzimy, że blisko 80% osób, które do nas przybyły i mogły podjąć pracę, tę pracę podjęły. To jest bardzo zdyscyplinowana grupa obywateli. Widzimy, że w","Zdajemy sobie oczywiście sprawę z tego, że potencjał naszej gospodarki cyfrowej jest gigantyczny, a tych zagrożeń, o czym mówią statystyki, dane przedstawiane r"
1,0.947,zwykły / zwykły,popiera / sprzeciwia się,"Po trzecie, rozsądne tempo wdrażania. Najważniejsza część dotycząca dotacji wchodzi w życie szybko, już dzień po ogłoszeniu ustawy, dzięki czemu Rada Ministrów","2. Dlaczego przepisy uchylające call-off stock mają wejść w życie dopiero 1 lipca 2028 r., skoro w uzasadnieniu przyznano, że dyrektywa 2025/516 wymaga przyjęci"
2,0.945,zwykły / zwykły,sprzeciwia się / popiera,"Proszę państwa, odniosę się też do innych kwestii. Wypisałem tu sobie mnóstwo rzeczy, w przypadku których składałem interpelacje do MON-u i w kwestii których są","W pierwszym etapie działania komisji deregulacyjnej ukazały ponad 100 różnych absurdów, które stosunkowo szybko i bardzo łatwo można uprościć. Rzeczywiście tak"
3,0.944,agresywny / agresywny,popiera / sprzeciwia się,"…w tym również do tej, przedstawiać kandydatury czterech naszych członków. I w tej komisji musimy mieć czterech członków, jeśli ona ma być zgodna z prawem. Jeśl","Pani Marszałek! Wysoka Izbo! Na początku tej kadencji bardzo dużo się nasłuchaliśmy o tym, że teraz w Sejmie będzie demokracja, będzie reprezentacja, będzie pra"
4,0.942,zwykły / agresywny,popiera / sprzeciwia się,"Należy podkreślić, że proponowane zmiany nie zamykają polskiego rynku zamówień publicznych, jeśli chodzi o wykonawców z państw trzecich, ale jasno wskazują to,","Zdajemy sobie oczywiście sprawę z tego, że potencjał naszej gospodarki cyfrowej jest gigantyczny, a tych zagrożeń, o czym mówią statystyki, dane przedstawiane r"


fastText (sentence vector) – najbardziej podobne pary o różnym tonie


,sim,ton A / B,postawa A / B,tekst A,tekst B
0,0.953,agresywny / zwykły,sprzeciwia się / popiera,"Natomiast, proszę państwa,? propos wypowiedzi poprzednika i głosów z sali, że mieliśmy do czynienia z przestępstwem, to oczywiście się rozstrzygnie. A ponieważ","Na koniec, panie ministrze, serdeczne podziękowania z ziemi podkarpackiej, ale również ode mnie. Jestem motocyklistą. Jeszcze chyba nikt nigdy tak jasno i prost"
1,0.948,zwykły / agresywny,popiera / sprzeciwia się,"Uważam, że projekt idzie w dobrym kierunku. Co prawda, jeśli chodzi o te przesłanki, o których wspomniał kolega Tumanowicz, które pozwalają wszcząć kontrolę, to","Natomiast, proszę państwa,? propos wypowiedzi poprzednika i głosów z sali, że mieliśmy do czynienia z przestępstwem, to oczywiście się rozstrzygnie. A ponieważ"
2,0.947,zwykły / agresywny,popiera / sprzeciwia się,"Na koniec, panie ministrze, serdeczne podziękowania z ziemi podkarpackiej, ale również ode mnie. Jestem motocyklistą. Jeszcze chyba nikt nigdy tak jasno i prost","Sami coś zrobili, nie było to najlepsze, więc my musimy to poprawiać, a oni mówią: nie, to wszystko nie tak powinno działać. Mówiąc wprost, nie mogę zrozumieć,"
3,0.947,agresywny / zwykły,sprzeciwia się / sprzeciwia się,"Kiedy teraz obniżacie składkę zdrowotną znowu dla działalności gospodarczych, to znów robicie to szybko. Nie wysyłacie nawet pisma związkom zawodowym do konsult","Przechodzę do drugiej sprawy. Pani minister, mówiła pani o problemie alkoholowym. Przypomnę pani, że dlatego, że Narodowy Fundusz Zdrowia nie płaci szpitalom, k"
4,0.947,zwykły / agresywny,sprzeciwia się / sprzeciwia się,"Pani Marszałek! Wysoki Sejmie! Będę kontynuował ten wątek, który był dzisiaj główny, jeżeli chodzi o posiedzenie Sejmu, a więc projektów aborcyjnych. Właśnie pr","Natomiast, proszę państwa,? propos wypowiedzi poprzednika i głosów z sali, że mieliśmy do czynienia z przestępstwem, to oczywiście się rozstrzygnie. A ponieważ"


fastText (sentence vector) – najbardziej podobne pary o przeciwnej postawie


,sim,ton A / B,postawa A / B,tekst A,tekst B
0,0.953,agresywny / zwykły,sprzeciwia się / popiera,"Natomiast, proszę państwa,? propos wypowiedzi poprzednika i głosów z sali, że mieliśmy do czynienia z przestępstwem, to oczywiście się rozstrzygnie. A ponieważ","Na koniec, panie ministrze, serdeczne podziękowania z ziemi podkarpackiej, ale również ode mnie. Jestem motocyklistą. Jeszcze chyba nikt nigdy tak jasno i prost"
1,0.952,agresywny / agresywny,popiera / sprzeciwia się,"Szanowny Panie Marszałku! Pan Minister! Wysoka Izbo! Właściwie nie miałem zabierać głosu, bo to jest zmiana prosta, właściwie gwarantująca wypłatę świadczeń nal","Panie Marszałku! Wysoka Izbo! Mówiłem o tym podczas pierwszego czytania tego projektu. Ten projekt jest przede wszystkim kpiną, ale to nie tyle kpina z Rozwoju"
2,0.950,zwykły / zwykły,sprzeciwia się / popiera,"Szanowny Panie Marszałku! Wysoka Izbo! Są co najmniej trzy powody, żeby w Polsce postawić wreszcie na trzyosobowe zespoły w karetkach, czego ta ustawa, żeby był","Na koniec, panie ministrze, serdeczne podziękowania z ziemi podkarpackiej, ale również ode mnie. Jestem motocyklistą. Jeszcze chyba nikt nigdy tak jasno i prost"
3,0.948,zwykły / agresywny,popiera / sprzeciwia się,"Uważam, że projekt idzie w dobrym kierunku. Co prawda, jeśli chodzi o te przesłanki, o których wspomniał kolega Tumanowicz, które pozwalają wszcząć kontrolę, to","Natomiast, proszę państwa,? propos wypowiedzi poprzednika i głosów z sali, że mieliśmy do czynienia z przestępstwem, to oczywiście się rozstrzygnie. A ponieważ"
4,0.948,zwykły / zwykły,popiera / sprzeciwia się,"Jestem bardzo wyczulony na każdy sygnał nepotyzmu, bo to się nadal zdarza. To jest w ogóle nieporównywalne z tym, co się działo za PiS-u, skala jest nieporównyw","Szanowny Panie Marszałku! Wysoka Izbo! Są co najmniej trzy powody, żeby w Polsce postawić wreszcie na trzyosobowe zespoły w karetkach, czego ta ustawa, żeby był"


### Zdania testowe

Kontrolowane pary: agresja vs ta sama krytyka bez agresji, ta sama treść innymi słowami, odwrócony sens tymi samymi słowami, krótka i długa wersja.

In [21]:
PROBES = {
    "A": "Klub Lewicy będzie głosował za przyjęciem tej ustawy.",
    "B": "Popieramy ten projekt i poprzemy go w głosowaniu.",
    "C": "Klub Lewicy będzie głosował przeciwko przyjęciu tej ustawy.",
    "D": "Szanowny Panie Marszałku! Wysoka Izbo! W imieniu naszego klubu chciałbym powiedzieć, że po długiej i "
         "wnikliwej analizie, po wielu spotkaniach z ekspertami, samorządowcami i stroną społeczną doszliśmy do "
         "wniosku, że ten projekt jest potrzebny, dlatego poprzemy go w głosowaniu.",
    "E": "Jesteście bandą kłamców i złodziei, którzy okradają Polaków.",
    "F": "Mamy poważne zastrzeżenia do tego projektu i nie możemy go poprzeć.",
    "G": "Ten rząd kłamie i okrada Polaków, to skandal i hańba.",
    "H": "Rząd przedstawia nieprecyzyjne dane i źle gospodaruje środkami publicznymi.",
}
PROBE_PAIRS = [("E", "G", "agresja vs agresja"), ("G", "H", "ta sama krytyka: agresywnie vs rzeczowo"),
               ("E", "F", "sprzeciw: agresja vs bez agresji"), ("F", "H", "rzeczowa krytyka vs rzeczowa krytyka"),
               ("A", "B", "ten sam sens, inne słowa"), ("A", "C", "przeciwny sens, te same słowa"),
               ("B", "D", "ten sam sens, krótkie vs długie")]

probe_vecs = {name: {k: f(t) for k, t in PROBES.items()} for name, f in TEXT_MODELS.items()}
cos = lambda a, b: float(a @ b / np.linalg.norm(a) / np.linalg.norm(b))
pd.DataFrame([{"para": f"{a}–{b}", "co porównujemy": desc,
               **{name: cos(v[a], v[b]) for name, v in probe_vecs.items()}} for a, b, desc in PROBE_PAIRS]).round(3)

,para,co porównujemy,Word2Vec (średnia),fastText (sentence vector)
0,E–G,agresja vs agresja,0.644,0.762
1,G–H,ta sama krytyka: agresywnie vs rzeczowo,0.627,0.612
2,E–F,sprzeciw: agresja vs bez agresji,0.447,0.514
3,F–H,rzeczowa krytyka vs rzeczowa krytyka,0.585,0.607
4,A–B,"ten sam sens, inne słowa",0.707,0.643
5,A–C,"przeciwny sens, te same słowa",0.931,0.926
6,B–D,"ten sam sens, krótkie vs długie",0.822,0.775


### Długość tekstu

Wektor tekstu to średnia wektorów słów: im więcej słów, tym bardziej kierunki się znoszą i wektor dąży do „przeciętnego tekstu”.

In [22]:
rows = []
for d in docs.sample(150, random_state=SEED).itertuples():
    tokens = TOKEN.findall(d.text)
    for n in (3, 5, 10, 20, 40, 80):
        if n <= len(tokens):
            prefix = " ".join(tokens[:n])
            for name, f in TEXT_MODELS.items():
                rows.append({"model": name, "n słów": n, "norma": np.linalg.norm(f(prefix))})
prefix_norms = pd.DataFrame(rows).groupby(["n słów", "model"]).norma.mean().unstack()
display(prefix_norms.round(3))

rows = []
for name, X in text_vecs.items():
    S = sims(X)
    np.fill_diagonal(S, np.nan)
    rows.append(pd.DataFrame({"model": name, "n_tokens": docs.n_tokens, "norma": np.linalg.norm(X, axis=1),
                              "średnie podobieństwo do innych": np.nanmean(S, axis=1)}))
length = pd.concat(rows)
display(length.groupby("model")[["n_tokens", "norma", "średnie podobieństwo do innych"]]
        .corr(method="spearman").xs("n_tokens", level=1).drop(columns="n_tokens").round(3))
px.scatter(length, x="n_tokens", y="średnie podobieństwo do innych", facet_col="model",
           title="Długość tekstu a średnie podobieństwo do pozostałych", width=950, height=400).show()

model,Word2Vec (średnia),fastText (sentence vector)
n słów,,
3,0.741,0.722
5,0.641,0.625
10,0.540,0.526
20,0.484,0.467
40,0.454,0.434
80,0.435,0.414


,norma,średnie podobieństwo do innych
model,,
Word2Vec (średnia),-0.381,0.639
fastText (sentence vector),-0.431,0.554


## Czy osadzenia nadają się do zadania?

5-krotna walidacja krzyżowa. Dla porównania: klasa większościowa i TF-IDF (worek słów) z tą samą regresją logistyczną.

In [23]:
tfidf = TfidfVectorizer(lowercase=True, min_df=2, ngram_range=(1, 2), sublinear_tf=True).fit_transform(docs.text)
FEATURES = {"TF-IDF (worek słów)": tfidf, **{name: unit(X) for name, X in text_vecs.items()}}

rows = []
for field in ("ton", "stance"):
    y = docs[field].to_numpy()
    rows.append({"etykieta": field, "cechy": "klasa większościowa",
                 "accuracy": pd.Series(y).value_counts(normalize=True).max(), "F1 makro": np.nan, "ROC AUC": 0.5 if field == "ton" else np.nan})
    for name, X in FEATURES.items():
        res = cross_validate(LogisticRegression(max_iter=5000, class_weight="balanced", C=1.0), X, y, cv=cv,
                             scoring=["accuracy", "f1_macro"] + (["roc_auc"] if field == "ton" else []))
        knn = cross_validate(KNeighborsClassifier(10, metric="cosine"), X, y, cv=cv, scoring=["accuracy"])
        rows.append({"etykieta": field, "cechy": name, "accuracy": res["test_accuracy"].mean(),
                     "F1 makro": res["test_f1_macro"].mean(),
                     "ROC AUC": res["test_roc_auc"].mean() if field == "ton" else np.nan,
                     "10-NN accuracy": knn["test_accuracy"].mean()})
results = pd.DataFrame(rows).set_index(["etykieta", "cechy"])
results.round(3)

accuracy  F1 makro  ROC AUC  \
etykieta cechy                                                     
ton      klasa większościowa            0.717       NaN    0.500   
         TF-IDF (worek słów)            0.808     0.758    0.877   
         Word2Vec (średnia)             0.793     0.768    0.861   
         fastText (sentence vector)     0.792     0.767    0.870   
stance   klasa większościowa            0.432       NaN      NaN   
         TF-IDF (worek słów)            0.588     0.561      NaN   
         Word2Vec (średnia)             0.602     0.590      NaN   
         fastText (sentence vector)     0.592     0.578      NaN   

                                     10-NN accuracy  
etykieta cechy                                       
ton      klasa większościowa                    NaN  
         TF-IDF (worek słów)                  0.760  
         Word2Vec (średnia)                   0.773  
         fastText (sentence vector)           0.808  
stance   klasa większościowa                    NaN  
         TF-IDF (worek słów)                  0.552  
         Word2Vec (średnia)                   0.543  
         fastText (sentence vector)           0.545

### Kontrola: agresja czy sprzeciw?

Agresja w anotacjach mocno pokrywa się z postawą (większość tekstów agresywnych to sprzeciw) i z klubem. Żeby sprawdzić, czy modele widzą agresję, a nie tylko „tekst opozycyjny”, powtarzamy klasyfikację tonu **tylko wśród tekstów sprzeciwiających się**.

In [24]:
sub = docs.stance.eq("sprzeciwia się").to_numpy()
y = docs.ton.to_numpy()[sub]
rows = [{"cechy": "klasa większościowa", "accuracy": pd.Series(y).value_counts(normalize=True).max(), "ROC AUC": 0.5}]
for name, X in FEATURES.items():
    res = cross_validate(LogisticRegression(max_iter=5000, class_weight="balanced"), X[sub], y, cv=cv,
                         scoring=["accuracy", "f1_macro", "roc_auc"])
    rows.append({"cechy": name, "accuracy": res["test_accuracy"].mean(), "F1 makro": res["test_f1_macro"].mean(),
                 "ROC AUC": res["test_roc_auc"].mean()})
for name, X in text_vecs.items():
    score = lda_scores(unit(X)[sub], y)
    rows.append({"cechy": f"LDA: {name}", "ROC AUC": roc_auc_score(y == "zwykły", score)})
print(f"{sub.sum()} tekstów sprzeciwiających się, w tym {(y == 'agresywny').sum()} agresywnych")
pd.DataFrame(rows).set_index("cechy").round(3)

216 tekstów sprzeciwiających się, w tym 134 agresywnych


,accuracy,ROC AUC,F1 makro
cechy,,,
klasa większościowa,0.620,0.500,NaN
TF-IDF (worek słów),0.796,0.840,0.766
Word2Vec (średnia),0.787,0.849,0.776
fastText (sentence vector),0.806,0.860,0.796
LDA: Word2Vec (średnia),NaN,0.834,NaN
LDA: fastText (sentence vector),NaN,0.851,NaN


In [25]:
pd.DataFrame({"LDA AUC słowa (Agresja vs pozostałe)": word_lda_auc,
              "LDA AUC teksty (agresywny vs zwykły)": dict(zip(word_lda_auc, text_lda_auc.values()))}).round(3)

,LDA AUC słowa (Agresja vs pozostałe),LDA AUC teksty (agresywny vs zwykły)
Word2Vec,0.843,0.873
fastText,0.832,0.886


## Dyskusja

Dane: 600 tekstów z `rest-annotations.json` (jeden anotator), 170 agresywnych (28%). Zawierają 342 spany `Agresja`, wszystkie w tekstach agresywnych, i 1156 spanów `Kontekst`. Etykietę `Agresja` ma 401 z 8824 słów treściowych (4,5%).

### Podsumowanie

| | Agresja | Postawa |
|---|---|---|
| słowa: LDA AUC poza próbą (Word2Vec / fastText) | 0,84 / 0,83 | – |
| słowa: silhouette | 0,015 / 0,020 | 0,002 / 0,004 (`Kontekst` popiera vs sprzeciw) |
| teksty: silhouette | 0,032 / 0,016 | −0,009 / −0,014 |
| teksty: regresja logistyczna, accuracy (klasa większościowa) | 0,79 / 0,79 (0,72) | 0,60 / 0,59 (0,43) |
| teksty: ROC AUC, regresja logistyczna / LDA | 0,86–0,87 / 0,87–0,89 | – |
| teksty: 10-NN accuracy | 0,77 / 0,81 | 0,54 / 0,55 |

- **Agresja jest w osadzeniach widoczna**, choć jeszcze nie bardzo wyraźnie. Na t-SNE nie tworzy osobnego skupiska: nienadzorowana redukcja wymiaru oddaje głównie temat. LDA znajduje jednak kierunek, który oddziela zarówno słowa ze spanów `Agresja`, jak i teksty agresywne (AUC 0,83–0,89 poza próbą).
- **Postawa jest bardzo trudna do uchwycenia prostymi metodami.** Silhouette jest bliskie zera lub ujemne, najbliżsi sąsiedzi są prawie losowi, a klasyfikacja wypada tylko nieco powyżej klasy większościowej. TF-IDF jest równie słaby (0,59), więc ograniczeniem jest uśrednianie i worek słów, a nie konkretny model.

### Osadzenia słów

**1. Czy osadzenia pre-trenowane dobrze odwzorowują znaczenie słów w korpusie sejmowym?**
Słownik pokrywają ogólnie dobrze (Word2Vec: 93% typów, fastText: 97%). **Najgorzej jednak pokrywają słowa agresywne:** 37 z 401 słów ze spanów `Agresja` nie ma w Word2Vec, a 25 nie ma w słowniku fastText. Należą do trzech grup:
- formy 2. osoby liczby mnogiej, czyli bezpośrednie zwroty do przeciwnika: *zawaliliście, okłamujecie, pogłębiacie, zafundowaliście, ukrywaliście*;
- polityczne neologizmy i obelgi: *putinflacja, patowładza, autokompromitacja, półinteligent*;
- nazwiska: *Giertych, Obajtek, Zandberg*.

Agresja w Sejmie jest więc w dużej części twórcza i skierowana do kogoś, a tego słownictwa w korpusach uczących brakuje. fastText może zbudować dla nich wektor z n-gramów, ale do porównania brane są tylko słowa obecne w obu modelach.
Znaczenia frazeologiczne też giną: *skok* (ze spanu *„skok na publiczne pieniądze”*) ma w obu modelach sąsiadów sportowych (*wzwyż, trójskok, przeskok*).

**2. Czy słowa grupują się według anotacji?**
- **Agresja: słabo, ale wyraźniej niż postawa.**
  - Silhouette jest bliskie zera (0,015 / 0,020), więc słowa agresywne nie tworzą skupiska.
  - Tworzą jednak sąsiedztwo: wśród 10 najbliższych sąsiadów słowa ze spanu `Agresja` 13,4% (Word2Vec) i 12,3% (fastText) to inne słowa ze spanów `Agresja`. Dla pozostałych słów to 3,1% / 2,8%, a w całym słowniku 4,4%.
  - LDA oddziela je z AUC 0,84 / 0,83 poza próbą. Kontrola tylko na słowach z 1–2 wystąpieniami daje 0,82, więc nie chodzi o samą różnicę częstości.
  - Sąsiedzi pokazują, że modele znają **słownictwo pejoratywne**: *nieudolności* → *niekompetencji, indolencji, nieporadności, opieszałości*; *kłamstwa* → *krętactwa, zakłamania, oszczerstwa*; *aferę* → *korupcyjną, łapówkarską, przekręty*.
  - Spany obejmują całe frazy, więc etykietę `Agresja` dostają też słowa neutralne (*apeluję, koalicję, społeczeństwo, sklepy*). To rozmywa grupę.
- **Statystyka i anotacja wskazują różne słowa.** Słowa najsilniej związane z tekstami agresywnymi (*pis, tusk, prezydenta, rząd, jesteście, waszego*) prawie nigdy nie są w spanach `Agresja` (0–25% wystąpień). Wskazują one **cel** ataku, a anotator zaznacza **ocenę** (*afera, kłamstwa, nieudolność, chaos, więzienie*).
- **Postawa (`Kontekst`): brak grupowania** (silhouette 0,002 / 0,004). Te same słowa (*projekt, ustawy, ochrony, bezpieczeństwo*) uzasadniają poparcie i sprzeciw. Osadzenia nie oddają też wydźwięku: *dobry–zły* ma 0,64 / 0,76, prawie tyle co *dobry–świetny* (0,76).

**3. Czym różnią się listy podobnych słów i skąd te różnice?**
Średnie nakładanie list top-10 wynosi 0,52 dla słów ze spanów `Agresja` i 0,34 dla słów z `Kontekst`.
- **Word2Vec** (NKJP i Wikipedia, formy wyrazowe) zwraca sąsiadów znaczeniowych: *aferę* → *korupcyjną, łapówkarską, przekręty*; *rozumiecie* → *wiecie, widzicie, pojmujecie*.
- **fastText** (Common Crawl, n-gramy znakowe) zwraca głównie warianty zapisu i odmiany: *aferę* → *aferkę, afere, Aferę, aferą*; *projekt* → *Projekt, -projekt, projekcik, .Projekt*. Częściej trafiają się też formy potoczne z internetu (*bajzel, zadymę*).

Wyższe nakładanie dla słów agresywnych wynika z tego, że wyrazy oceniające (*chaos, kłamstwa, nieudolności*) mają w obu modelach te same, jednoznaczne synonimy. Słowa z `Kontekst` (*projekt, ustawa*) mają w fastText wiele wariantów zapisu.

**4. Jak można ulepszyć osadzenia?**
- **Douczyć na korpusie PPC** (ok. 14,7 mln słów). To pokryje formy 2. osoby liczby mnogiej, neologizmy i nazwiska.
- **Osadzać frazy, a nie pojedyncze słowa** (*skok na pieniądze*, *pustego w próżne*), bo spany `Agresja` to w większości frazy.
- **Retrofitting do słowników wydźwięku i obelg.**
- **Modele kontekstowe** (HerBERT), które rozumieją idiomy, negację i cel wypowiedzi. Bez nich nie ma szans na postawę.

### Osadzenia tekstów

**1. Czy model uznał za podobne zdania, które różnią się znaczeniem?**
Tak. Najbardziej podobne pary o przeciwnej postawie mają 0,94–0,95. *„Klub Lewicy będzie głosował **za** przyjęciem tej ustawy”* i *„… **przeciwko** …”* mają 0,93 w obu modelach, najwięcej spośród par testowych. Uśrednianie gubi negację i kolejność słów.

**2. Czy są zdania semantycznie podobne, które model uznał za odległe?**
Tak. Parafraza poparcia innymi słowami ma tylko 0,71 / 0,64.
Ta sama krytyka rządu wyrażona agresywnie i rzeczowo (G–H) ma 0,63 / 0,61, czyli mniej niż dwie różne wypowiedzi agresywne w fastText (E–G: 0,76). fastText częściowo grupuje agresję niezależnie od treści. W Word2Vec ta różnica jest niewielka (0,64 vs 0,63).

**3. Czy zdania o różnej długości i podobnym sensie są traktowane podobnie?**
Częściowo. Krótka deklaracja i jej długa wersja z formułami grzecznościowymi mają 0,82 / 0,78, mniej niż para *za / przeciw*.

**4. Czy długość wpływa na „wyrazistość” wektora?**
Tak.
- **Norma maleje z długością:** z 0,74 (3 słowa) do 0,43 (80 słów).
- **Długie teksty są podobne do wszystkiego:** korelacja Spearmana długości ze średnim podobieństwem do innych tekstów wynosi 0,64 / 0,55. Długie teksty stają się „hubami”.

Teksty agresywne i zwykłe mają podobną długość (54 vs 52 słowa), więc długość nie tłumaczy wykrywalności agresji.

**5. Czy osadzenia nadają się do zadania?**
- **Do wykrywania agresji: jako punkt wyjścia tak.** ROC AUC wynosi 0,86–0,87, a 10-NN dla fastText daje 0,81 accuracy.
  Agresja mocno pokrywa się ze sprzeciwem (134 z 170 tekstów agresywnych) i z klubem (PiS 48%, Konfederacja 41%, PSL-TD 11% tekstów agresywnych). Klasyfikacja **tylko wśród tekstów sprzeciwiających się** nadal daje AUC 0,84–0,86 (LDA 0,83–0,85) przy 62% dla klasy większościowej. Modele widzą więc agresję, a nie tylko „tekst opozycyjny”. Zależności od klubu ta kontrola nie wyklucza.
- **Do postawy: nie w tej postaci.** Potrzebny jest model, który uwzględnia cel wypowiedzi i negację: dostrojony HerBERT albo cechy zbudowane na spanach `Kontekst`.